# KHÁM PHÁ DỮ LIỆU CHUYẾN BAY - EDA

## Đề tài
**Phân tích tình trạng chậm chuyến bay theo hãng hàng không, sân bay và thời gian**

## Mục tiêu EDA

Notebook này được sử dụng để:

- kiểm tra cấu trúc dữ liệu sau tiền xử lý;
- kiểm tra kiểu dữ liệu và giá trị thiếu;
- thống kê mô tả độ trễ chuyến bay;
- khảo sát phân bố `ArrDelay`;
- kiểm tra các giá trị ngoại lai;
- phân tích sơ bộ tình trạng chậm chuyến theo thời gian;
- phân tích theo hãng hàng không, sân bay, tuyến bay và nguyên nhân chậm;
- kiểm tra dữ liệu trước khi xây dựng dashboard Streamlit.


## 1. Import thư viện và cấu hình màu

In [43]:
from pathlib import Path

import pandas as pd
import matplotlib.pyplot as plt
import plotly.express as px

pd.set_option("display.max_columns", 100)
pd.set_option("display.float_format", lambda x: f"{x:,.2f}")

# Bảng màu đồng bộ với dashboard
COLORS = {
    "navy": "#123A72",
    "blue": "#1976E9",
    "blue_light": "#74B9FF",
    "blue_soft": "#DCEEFF",
    "orange": "#FF9F43",
    "orange_light": "#FFC078",
    "teal": "#20BFA9",
    "red": "#EF5350",
    "text": "#23415F",
    "muted": "#6E879E",
    "grid": "#E8F0F7",
    "white": "#FFFFFF",
}

def style_figure(fig, title=None):
    if title is not None:
        fig.update_layout(title=title)

    fig.update_layout(
        template="plotly_white",
        paper_bgcolor=COLORS["white"],
        plot_bgcolor=COLORS["white"],
        font=dict(
            family="Arial",
            size=13,
            color=COLORS["text"],
        ),
        title=dict(
            font=dict(
                size=20,
                color=COLORS["navy"],
            )
        ),
        margin=dict(
            l=60,
            r=40,
            t=70,
            b=55,
        ),
    )

    fig.update_xaxes(
        gridcolor=COLORS["grid"],
        zeroline=False,
    )

    fig.update_yaxes(
        gridcolor=COLORS["grid"],
        zeroline=False,
    )

    return fig

## 2. Xác định đường dẫn project

In [44]:
CURRENT_DIR = Path.cwd().resolve()

if (CURRENT_DIR / "data").exists():
    ROOT = CURRENT_DIR
elif (CURRENT_DIR.parent / "data").exists():
    ROOT = CURRENT_DIR.parent
else:
    raise FileNotFoundError(
        "Không tìm thấy thư mục data/. "
        "Hãy mở notebook từ project flight_delay."
    )

FEATURES_DIR = ROOT / "data" / "processed" / "monthly_features"
ANALYSIS_DIR = ROOT / "data" / "analysis"

print("ROOT:", ROOT)
print("FEATURES_DIR:", FEATURES_DIR)
print("ANALYSIS_DIR:", ANALYSIS_DIR)

ROOT: /Users/nguyentuyetmai/Downloads/flight_delay
FEATURES_DIR: /Users/nguyentuyetmai/Downloads/flight_delay/data/processed/monthly_features
ANALYSIS_DIR: /Users/nguyentuyetmai/Downloads/flight_delay/data/analysis


## 3. Kiểm tra các file dữ liệu đã tạo

In [45]:
def month_number(path):
    return int(path.stem.split("_")[1])

files = sorted(
    FEATURES_DIR.glob("*_features.parquet"),
    key=month_number
)

print(f"Số file monthly features: {len(files)}")

for file in files:
    print(file.name)

if len(files) != 12:
    print(
        "\nCẢNH BÁO: Kỳ vọng 12 file, "
        "mỗi file tương ứng một tháng năm 2025."
    )

Số file monthly features: 12
2025_1_features.parquet
2025_2_features.parquet
2025_3_features.parquet
2025_4_features.parquet
2025_5_features.parquet
2025_6_features.parquet
2025_7_features.parquet
2025_8_features.parquet
2025_9_features.parquet
2025_10_features.parquet
2025_11_features.parquet
2025_12_features.parquet


## 4. Kiểm tra cấu trúc dữ liệu

Để tránh sử dụng quá nhiều RAM, phần kiểm tra chi tiết sử dụng dữ liệu tháng 1/2025.  
Các kết luận toàn năm ở phần sau sử dụng các bảng tổng hợp từ `data/analysis/`.


In [46]:
sample_file = FEATURES_DIR / "2025_1_features.parquet"

df = pd.read_parquet(sample_file)

df.head()

,Year,Quarter,Month,DayofMonth,DayOfWeek,FlightDate,Reporting_Airline,Flight_Number_Reporting_Airline,Origin,Dest,CRSDepTime,DepTime,DepDelay,DepDelayMinutes,CRSArrTime,ArrTime,ArrDelay,ArrDelayMinutes,Cancelled,CancellationCode,Diverted,Distance,CarrierDelay,WeatherDelay,NASDelay,SecurityDelay,LateAircraftDelay,Airline_Name,Origin_Airport,Origin_City,Origin_State,Origin_Country,Origin_Latitude,Origin_Longitude,Dest_Airport,Dest_City,Dest_State,Dest_Country,Dest_Latitude,Dest_Longitude,Month_Name,Day_Name,Dep_Hour,Time_Group,Route,Valid_Arrival_Delay,Is_Delayed,Delay_Category,Is_Cancelled,Is_Diverted
0,2025,1,1,1,3,2025-01-01,AA,1,JFK,LAX,659.00,656.00,-3.00,0.00,"1,020.00","1,013.00",-7.00,0.00,0.00,None,0.00,"2,475.00",0.00,0.00,0.00,0.00,0.00,American Airlines Inc.,John F. Kennedy International Airport (New Yor...,New York,NY,USA,40.64,-73.78,Los Angeles International Airport,Los Angeles,CA,USA,33.94,-118.41,January,Wednesday,6,06-08,JFK → LAX,True,False,On Time,False,False
1,2025,1,1,2,4,2025-01-02,AA,1,JFK,LAX,659.00,652.00,-7.00,0.00,"1,020.00","1,022.00",2.00,2.00,0.00,None,0.00,"2,475.00",0.00,0.00,0.00,0.00,0.00,American Airlines Inc.,John F. Kennedy International Airport (New Yor...,New York,NY,USA,40.64,-73.78,Los Angeles International Airport,Los Angeles,CA,USA,33.94,-118.41,January,Thursday,6,06-08,JFK → LAX,True,False,On Time,False,False
2,2025,1,1,3,5,2025-01-03,AA,1,JFK,LAX,659.00,652.00,-7.00,0.00,"1,020.00","1,003.00",-17.00,0.00,0.00,None,0.00,"2,475.00",0.00,0.00,0.00,0.00,0.00,American Airlines Inc.,John F. Kennedy International Airport (New Yor...,New York,NY,USA,40.64,-73.78,Los Angeles International Airport,Los Angeles,CA,USA,33.94,-118.41,January,Friday,6,06-08,JFK → LAX,True,False,On Time,False,False
3,2025,1,1,4,6,2025-01-04,AA,1,JFK,LAX,700.00,653.00,-7.00,0.00,"1,026.00","1,016.00",-10.00,0.00,0.00,None,0.00,"2,475.00",0.00,0.00,0.00,0.00,0.00,American Airlines Inc.,John F. Kennedy International Airport (New Yor...,New York,NY,USA,40.64,-73.78,Los Angeles International Airport,Los Angeles,CA,USA,33.94,-118.41,January,Saturday,7,06-08,JFK → LAX,True,False,On Time,False,False
4,2025,1,1,5,7,2025-01-05,AA,1,JFK,LAX,659.00,655.00,-4.00,0.00,"1,020.00","1,013.00",-7.00,0.00,0.00,None,0.00,"2,475.00",0.00,0.00,0.00,0.00,0.00,American Airlines Inc.,John F. Kennedy International Airport (New Yor...,New York,NY,USA,40.64,-73.78,Los Angeles International Airport,Los Angeles,CA,USA,33.94,-118.41,January,Sunday,6,06-08,JFK → LAX,True,False,On Time,False,False


In [47]:
print("Số dòng:", f"{df.shape[0]:,}")
print("Số cột:", df.shape[1])

Số dòng: 539,747
Số cột: 50


In [48]:
df.columns.tolist()

['Year',
 'Quarter',
 'Month',
 'DayofMonth',
 'DayOfWeek',
 'FlightDate',
 'Reporting_Airline',
 'Flight_Number_Reporting_Airline',
 'Origin',
 'Dest',
 'CRSDepTime',
 'DepTime',
 'DepDelay',
 'DepDelayMinutes',
 'CRSArrTime',
 'ArrTime',
 'ArrDelay',
 'ArrDelayMinutes',
 'Cancelled',
 'CancellationCode',
 'Diverted',
 'Distance',
 'CarrierDelay',
 'WeatherDelay',
 'NASDelay',
 'SecurityDelay',
 'LateAircraftDelay',
 'Airline_Name',
 'Origin_Airport',
 'Origin_City',
 'Origin_State',
 'Origin_Country',
 'Origin_Latitude',
 'Origin_Longitude',
 'Dest_Airport',
 'Dest_City',
 'Dest_State',
 'Dest_Country',
 'Dest_Latitude',
 'Dest_Longitude',
 'Month_Name',
 'Day_Name',
 'Dep_Hour',
 'Time_Group',
 'Route',
 'Valid_Arrival_Delay',
 'Is_Delayed',
 'Delay_Category',
 'Is_Cancelled',
 'Is_Diverted']

### Nhận xét

Dữ liệu đã được rút gọn còn các thuộc tính cần thiết cho đề tài thay vì sử dụng toàn bộ các trường của BTS gốc. Điều này giúp giảm dung lượng, giảm mức sử dụng RAM và làm rõ mục tiêu phân tích.


## 5. Kiểm tra kiểu dữ liệu

In [49]:
dtype_table = (
    df.dtypes
    .astype(str)
    .reset_index()
)

dtype_table.columns = [
    "Column",
    "Data_Type"
]

dtype_table

,Column,Data_Type
0,Year,int32
1,Quarter,int32
2,Month,int32
3,DayofMonth,int32
4,DayOfWeek,int32
5,FlightDate,datetime64[ns]
6,Reporting_Airline,string
7,Flight_Number_Reporting_Airline,int64
8,Origin,string
9,Dest,string


## 6. Kiểm tra dữ liệu thiếu

In [50]:
missing = pd.DataFrame({
    "Missing_Count": df.isna().sum(),
    "Missing_Percent": df.isna().mean() * 100
})

missing = (
    missing
    .sort_values(
        "Missing_Percent",
        ascending=False
    )
)

missing.head(25)

,Missing_Count,Missing_Percent
CancellationCode,523435,96.98
Airline_Name,58272,10.80
ArrDelay,17478,3.24
ArrDelayMinutes,17478,3.24
Delay_Category,17478,3.24
Is_Delayed,17478,3.24
ArrTime,16580,3.07
DepDelay,15923,2.95
DepDelayMinutes,15923,2.95
DepTime,15886,2.94


### Nhận xét về dữ liệu thiếu

Không phải mọi giá trị thiếu đều là dữ liệu sai.

- `ArrDelay` có thể thiếu đối với chuyến bị hủy hoặc chuyển hướng.
- `CancellationCode` thường thiếu đối với chuyến không bị hủy.
- Một số trường nguyên nhân chậm có thể không được ghi nhận nếu chuyến không thuộc nhóm cần báo cáo nguyên nhân.
- Không sử dụng `dropna()` cho toàn bộ DataFrame vì có thể làm mất các chuyến bay hợp lệ.


## 7. Kiểm tra dữ liệu trùng

In [51]:
duplicate_count = df.duplicated().sum()

print(
    "Số dòng trùng hoàn toàn:",
    f"{duplicate_count:,}"
)

Số dòng trùng hoàn toàn: 0


## 8. Thống kê mô tả độ trễ

Chỉ các chuyến thỏa mãn:

- `Cancelled == 0`;
- `Diverted == 0`;
- `ArrDelay` không thiếu;

mới được xem là hợp lệ để phân tích độ trễ khi đến.


In [52]:
valid = df[
    df["Valid_Arrival_Delay"]
].copy()

print(
    "Số chuyến hợp lệ để phân tích ArrDelay:",
    f"{len(valid):,}"
)

Số chuyến hợp lệ để phân tích ArrDelay: 522,269


In [53]:
columns_to_describe = [
    col
    for col in [
        "ArrDelay",
        "DepDelay",
        "Distance",
    ]
    if col in valid.columns
]

valid[columns_to_describe].describe()

,ArrDelay,DepDelay,Distance
count,"522,269.00","522,269.00","522,269.00"
mean,3.76,10.24,847.16
std,56.85,53.93,601.92
min,-87.00,-50.00,31.00
25%,-18.00,-6.00,403.00
50%,-8.00,-3.00,712.00
75%,7.00,6.00,"1,085.00"
max,"3,282.00","3,298.00","5,095.00"


## 9. Kiểm tra giá trị âm và giá trị lớn

In [54]:
print("ArrDelay nhỏ nhất:", valid["ArrDelay"].min())
print("ArrDelay lớn nhất:", valid["ArrDelay"].max())

print(
    "Số chuyến ArrDelay < 0:",
    f"{(valid['ArrDelay'] < 0).sum():,}"
)

print(
    "Số chuyến ArrDelay > 300:",
    f"{(valid['ArrDelay'] > 300).sum():,}"
)

ArrDelay nhỏ nhất: -87.0
ArrDelay lớn nhất: 3282.0
Số chuyến ArrDelay < 0: 341,773
Số chuyến ArrDelay > 300: 2,453


### Giải thích

`ArrDelay < 0` không phải dữ liệu sai. Giá trị âm thể hiện chuyến bay đến sớm hơn lịch dự kiến nên được giữ lại.

Các giá trị độ trễ rất lớn cũng không tự động bị xóa vì chậm chuyến hàng trăm phút vẫn có thể xảy ra trong thực tế. Việc giới hạn khoảng hiển thị ở biểu đồ bên dưới chỉ phục vụ trực quan hóa, không làm thay đổi dữ liệu gốc.


## 10. Phân bố độ trễ khi đến

In [55]:
zoom_delay = valid[
    valid["ArrDelay"].between(
        -60,
        300
    )
]

fig = px.histogram(
    zoom_delay,
    x="ArrDelay",
    nbins=80,
    labels={
        "ArrDelay": "Độ trễ khi đến (phút)"
    },
)

fig.update_traces(
    marker_color=COLORS["blue"]
)

style_figure(
    fig,
    "Phân bố độ trễ khi đến (-60 đến 300 phút)"
)

fig.show()

## 11. Boxplot ArrDelay

In [56]:
fig = px.box(
    zoom_delay,
    y="ArrDelay",
    labels={
        "ArrDelay": "Độ trễ khi đến (phút)"
    },
)

fig.update_traces(
    marker_color=COLORS["blue"]
)

style_figure(
    fig,
    "Boxplot ArrDelay trong khoảng -60 đến 300 phút"
)

fig.show()

## 12. Phân bố mức độ chậm

In [57]:
delay_category = (
    df["Delay_Category"]
    .value_counts(dropna=False)
    .rename_axis("Delay_Category")
    .reset_index(name="Flights")
)

delay_category

,Delay_Category,Flights
0,On Time,427445
1,16-30 min,33561
2,31-60 min,28584
3,61-120 min,19359
4,<NA>,17478
5,>120 min,13320


In [58]:
fig = px.bar(
    delay_category,
    x="Delay_Category",
    y="Flights",
    labels={
        "Delay_Category": "Mức độ chậm",
        "Flights": "Số chuyến"
    },
)

fig.update_traces(
    marker_color=COLORS["blue_light"]
)

style_figure(
    fig,
    "Số chuyến theo mức độ chậm"
)

fig.show()

# PHÂN TÍCH TOÀN NĂM 2025

Các phần dưới đây sử dụng các bảng tổng hợp do `src/analysis.py` tạo ra từ toàn bộ 12 tháng. Cách này tránh phải nối khoảng 7 triệu dòng vào một DataFrame duy nhất trong notebook.


## 13. KPI tổng quan

In [59]:
kpi = pd.read_csv(
    ANALYSIS_DIR / "kpi_summary.csv"
)

kpi

,Metric,Value
0,Total Flights,"7,001,619.00"
1,Valid Flights,"6,879,484.00"
2,Delayed Flights,"1,487,713.00"
3,Delay Rate (%),21.63
4,Average Arrival Delay,8.50
5,Average Delay Minutes,74.77
6,Cancelled Flights,"102,876.00"
7,Cancel Rate (%),1.47
8,Diverted Flights,"19,258.00"
9,Diverted Rate (%),0.28


In [60]:
def get_metric(name):
    row = kpi.loc[
        kpi["Metric"] == name,
        "Value"
    ]

    return row.iloc[0] if not row.empty else None


print("Total Flights:", f"{get_metric('Total Flights'):,.0f}")
print("Delayed Flights:", f"{get_metric('Delayed Flights'):,.0f}")
print("Delay Rate (%):", f"{get_metric('Delay Rate (%)'):.2f}%")

print(
    "Average Delay Minutes:",
    f"{get_metric('Average Delay Minutes'):.2f} phút"
)

print(
    "Cancel Rate (%):",
    f"{get_metric('Cancel Rate (%)'):.2f}%"
)

Total Flights: 7,001,619
Delayed Flights: 1,487,713
Delay Rate (%): 21.63%
Average Delay Minutes: 74.77 phút
Cancel Rate (%): 1.47%


## 14. Tỷ lệ chậm chuyến theo tháng

In [61]:
month = pd.read_csv(
    ANALYSIS_DIR / "delay_by_month.csv"
)

month = month.sort_values("Month")

month

,Month,Month_Name,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,1,January,539747,522269,94824,18.16,3.76,72.71
1,2,February,504884,496476,99891,20.12,5.72,73.71
2,3,March,600872,592301,112410,18.98,5.45,74.05
3,4,April,583950,577730,109771,19.00,5.66,70.91
4,5,May,605648,597574,136676,22.87,10.19,74.30
5,6,June,611575,599472,164851,27.50,15.59,78.33
6,7,July,631428,612811,172513,28.15,17.35,83.18
7,8,August,602378,593733,129799,21.86,9.24,75.17
8,9,September,562439,558328,89572,16.04,2.32,68.94
9,10,October,605844,601570,117898,19.60,5.59,65.96


In [62]:
fig = px.line(
    month,
    x="Month_Name",
    y="Delay_Rate",
    markers=True,
    labels={
        "Month_Name": "Tháng",
        "Delay_Rate": "Tỷ lệ chậm (%)"
    },
)

fig.update_traces(
    line=dict(
        color=COLORS["blue"],
        width=3,
    ),
    marker=dict(
        color=COLORS["blue"],
        size=8,
    )
)

style_figure(
    fig,
    "Tỷ lệ chậm chuyến theo tháng"
)

fig.show()

In [63]:
highest_month = month.loc[
    month["Delay_Rate"].idxmax()
]

print(
    f"Tháng có tỷ lệ chậm cao nhất: "
    f"{highest_month['Month_Name']} "
    f"({highest_month['Delay_Rate']:.2f}%)"
)

Tháng có tỷ lệ chậm cao nhất: July (28.15%)


## 15. Tỷ lệ chậm chuyến theo ngày trong tuần

In [64]:
day = pd.read_csv(
    ANALYSIS_DIR / "delay_by_day.csv"
)

day = day.sort_values("DayOfWeek")

day

,DayOfWeek,Day_Name,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,1,Monday,1050150,1031857,238061,23.07,10.15,75.50
1,2,Tuesday,945648,931999,165801,17.79,4.11,73.01
2,3,Wednesday,966102,951705,177582,18.66,5.00,72.26
3,4,Thursday,1040825,1021742,230775,22.59,9.55,73.52
4,5,Friday,1044333,1024839,230945,22.53,9.49,73.84
5,6,Saturday,906399,890640,181366,20.36,6.91,74.44
6,7,Sunday,1048162,1026702,263183,25.63,13.45,79.04


In [65]:
max_idx = day["Delay_Rate"].idxmax()

bar_colors = [
    COLORS["orange"]
    if idx == max_idx
    else COLORS["blue_light"]
    for idx in day.index
]

fig = px.bar(
    day,
    x="Day_Name",
    y="Delay_Rate",
    labels={
        "Day_Name": "Ngày",
        "Delay_Rate": "Tỷ lệ chậm (%)"
    },
    text="Delay_Rate"
)

fig.update_traces(
    marker_color=bar_colors,
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Tỷ lệ chậm chuyến theo ngày trong tuần"
)

fig.show()

In [66]:
highest_day = day.loc[
    day["Delay_Rate"].idxmax()
]

print(
    f"Ngày có tỷ lệ chậm cao nhất: "
    f"{highest_day['Day_Name']} "
    f"({highest_day['Delay_Rate']:.2f}%)"
)

Ngày có tỷ lệ chậm cao nhất: Sunday (25.63%)


## 16. Tỷ lệ chậm chuyến theo khung giờ

In [67]:
time_group = pd.read_csv(
    ANALYSIS_DIR / "delay_by_time_group.csv"
)

time_order = [
    "00-05",
    "06-08",
    "09-11",
    "12-14",
    "15-17",
    "18-20",
    "21-23",
]

time_group["Time_Group"] = pd.Categorical(
    time_group["Time_Group"],
    categories=time_order,
    ordered=True
)

time_group = time_group.sort_values("Time_Group")

time_group

,Time_Group,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,00-05,215288,211729,19385,9.16,-2.20,100.57
1,06-08,1475845,1454830,173343,11.92,-0.66,76.43
2,09-11,1266715,1250047,211521,16.92,3.32,68.52
3,12-14,1236027,1216478,272836,22.43,9.36,73.07
4,15-17,1247046,1222212,352659,28.85,15.85,75.77
5,18-20,1112306,1086327,339316,31.24,17.63,76.38
6,21-23,448392,437861,118653,27.10,13.40,75.58


In [68]:
max_idx = time_group["Delay_Rate"].idxmax()

bar_colors = [
    COLORS["orange"]
    if idx == max_idx
    else COLORS["blue"]
    for idx in time_group.index
]

fig = px.bar(
    time_group,
    x="Time_Group",
    y="Delay_Rate",
    labels={
        "Time_Group": "Khung giờ",
        "Delay_Rate": "Tỷ lệ chậm (%)"
    },
    text="Delay_Rate"
)

fig.update_traces(
    marker_color=bar_colors,
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Tỷ lệ chậm chuyến theo khung giờ"
)

fig.show()

In [69]:
highest_time_group = time_group.loc[
    time_group["Delay_Rate"].idxmax()
]

print(
    f"Khung giờ có tỷ lệ chậm cao nhất: "
    f"{highest_time_group['Time_Group']} "
    f"({highest_time_group['Delay_Rate']:.2f}%)"
)

Khung giờ có tỷ lệ chậm cao nhất: 18-20 (31.24%)


## 17. Phân tích theo hãng hàng không

Không nên chỉ so sánh số chuyến bị trễ tuyệt đối vì hãng có nhiều chuyến sẽ tự nhiên có nhiều chuyến trễ hơn. Vì vậy sử dụng `Delay_Rate` để so sánh.


In [70]:
airline = pd.read_csv(
    ANALYSIS_DIR / "delay_by_airline.csv"
)

top_airline = (
    airline
    .sort_values(
        "Delay_Rate",
        ascending=False
    )
    .head(10)
)

top_airline

,Reporting_Airline,Airline_Name,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,F9,Frontier Airlines Inc.,198065,194192,52948,27.27,14.84,86.06
1,OH,NaN,248735,236682,63548,26.85,17.32,92.99
2,B6,JetBlue Airways,231413,226703,57769,25.48,10.95,77.75
3,AA,American Airlines Inc.,973653,952841,238230,25.00,13.69,85.24
4,G4,NaN,130899,129892,31601,24.33,13.01,87.24
5,AS,Alaska Airlines Inc.,245588,241927,53638,22.17,4.80,52.89
6,YX,NaN,346036,334043,69891,20.92,6.39,73.46
7,NK,Spirit Air Lines,194515,191191,39906,20.87,6.60,75.89
8,UA,United Air Lines Inc.,795271,786377,163329,20.77,7.31,74.47
9,WN,Southwest Airlines Co.,1391885,1376837,284089,20.63,6.05,58.53


In [71]:
airline_label = (
    "Airline_Name"
    if "Airline_Name" in top_airline.columns
    else "Reporting_Airline"
)

plot_airline = (
    top_airline
    .sort_values("Delay_Rate")
    .copy()
)

max_idx = plot_airline["Delay_Rate"].idxmax()

bar_colors = [
    COLORS["orange"]
    if idx == max_idx
    else COLORS["blue_light"]
    for idx in plot_airline.index
]

fig = px.bar(
    plot_airline,
    x="Delay_Rate",
    y=airline_label,
    orientation="h",
    labels={
        "Delay_Rate": "Tỷ lệ chậm (%)",
        airline_label: "Hãng hàng không"
    },
    text="Delay_Rate"
)

fig.update_traces(
    marker_color=bar_colors,
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Top 10 hãng có tỷ lệ chậm chuyến cao nhất"
)

fig.show()

In [72]:
highest_airline = top_airline.iloc[0]

print(
    f"Hãng có tỷ lệ chậm cao nhất: "
    f"{highest_airline[airline_label]} "
    f"({highest_airline['Delay_Rate']:.2f}%)"
)

Hãng có tỷ lệ chậm cao nhất: Frontier Airlines Inc. (27.27%)


## 18. Phân tích sân bay đi

In [73]:
origin = pd.read_csv(
    ANALYSIS_DIR / "delay_by_origin.csv"
)

top_origin = (
    origin
    .sort_values(
        "Delay_Rate",
        ascending=False
    )
    .head(10)
)

top_origin

,Origin,Origin_Airport,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,CKB,NaN,205,199,102,51.26,68.42,137.03
1,VRB,NaN,42,41,21,51.22,48.32,97.95
2,HGR,NaN,316,308,147,47.73,45.12,99.81
3,USA,NaN,710,703,312,44.38,41.77,102.64
4,DHN,Dothan Regional Airport,52,52,23,44.23,96.85,234.04
5,HTS,NaN,540,531,231,43.50,35.13,90.61
6,TOL,Toledo Express Airport,396,393,155,39.44,27.24,84.54
7,ASE,Aspen-Pitkin County Airport,7685,7207,2419,33.56,26.12,102.99
8,SUX,Sioux Gateway Airport,729,711,230,32.35,28.33,101.55
9,SCK,NaN,564,555,172,30.99,31.94,119.81


In [74]:
plot_origin = (
    top_origin
    .sort_values("Delay_Rate")
    .copy()
)

max_idx = plot_origin["Delay_Rate"].idxmax()

bar_colors = [
    COLORS["orange"]
    if idx == max_idx
    else COLORS["blue_light"]
    for idx in plot_origin.index
]

fig = px.bar(
    plot_origin,
    x="Delay_Rate",
    y="Origin",
    orientation="h",
    labels={
        "Delay_Rate": "Tỷ lệ chậm (%)",
        "Origin": "Sân bay đi"
    },
    text="Delay_Rate"
)

fig.update_traces(
    marker_color=bar_colors,
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Top 10 sân bay đi có tỷ lệ chậm cao nhất"
)

fig.show()

## 19. Phân tích sân bay đến

In [75]:
destination = pd.read_csv(
    ANALYSIS_DIR / "delay_by_destination.csv"
)

top_destination = (
    destination
    .sort_values(
        "Delay_Rate",
        ascending=False
    )
    .head(10)
)

top_destination

,Dest,Dest_Airport,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,VRB,NaN,42,41,21,51.22,32.68,73.29
1,DHN,Dothan Regional Airport,52,52,23,44.23,50.63,122.13
2,HGR,NaN,315,310,129,41.61,25.84,69.50
3,USA,NaN,711,706,285,40.37,24.24,67.39
4,CKB,NaN,205,200,78,39.00,32.61,90.21
5,SFB,NaN,10497,10425,3709,35.58,28.18,95.49
6,HTS,NaN,540,531,185,34.84,19.95,70.91
7,HOB,Lea County Regional Airport,730,704,226,32.10,32.49,122.92
8,SLN,NaN,971,942,300,31.85,30.51,114.03
9,PIE,NaN,9415,9317,2934,31.49,19.86,85.94


In [76]:
plot_destination = (
    top_destination
    .sort_values("Delay_Rate")
    .copy()
)

max_idx = plot_destination["Delay_Rate"].idxmax()

bar_colors = [
    COLORS["orange"]
    if idx == max_idx
    else COLORS["blue_light"]
    for idx in plot_destination.index
]

fig = px.bar(
    plot_destination,
    x="Delay_Rate",
    y="Dest",
    orientation="h",
    labels={
        "Delay_Rate": "Tỷ lệ chậm (%)",
        "Dest": "Sân bay đến"
    },
    text="Delay_Rate"
)

fig.update_traces(
    marker_color=bar_colors,
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Top 10 sân bay đến có tỷ lệ chậm cao nhất"
)

fig.show()

## 20. Phân tích tuyến bay

`analysis.py` đã đặt ngưỡng số chuyến tối thiểu trước khi so sánh tuyến bay. Điều này hạn chế trường hợp một tuyến có rất ít chuyến nhưng có `Delay_Rate = 100%`, gây kết luận thiếu tin cậy.


In [77]:
route = pd.read_csv(
    ANALYSIS_DIR / "delay_by_route.csv"
)

top_route = (
    route
    .sort_values(
        "Delay_Rate",
        ascending=False
    )
    .head(10)
)

top_route

,Origin,Dest,Route,Total_Flights,Valid_Flights,Delayed_Flights,Delay_Rate,Avg_Arrival_Delay,Avg_Delay_Minutes
0,ROA,SFB,ROA → SFB,128,125.00,82,65.60,68.91,106.85
1,TRI,SFB,TRI → SFB,124,123.00,78,63.41,50.82,83.88
2,LEX,SFB,LEX → SFB,224,220.00,135,61.36,62.93,107.07
3,CKB,SFB,CKB → SFB,113,112.00,68,60.71,91.89,152.00
4,SFB,ROA,SFB → ROA,128,125.00,72,57.60,53.38,94.47
5,SFB,USA,SFB → USA,200,198.00,113,57.07,39.36,70.04
6,CHA,SFB,CHA → SFB,132,132.00,74,56.06,41.45,74.84
7,SFB,GSP,SFB → GSP,113,113.00,63,55.75,47.92,86.89
8,GSP,SFB,GSP → SFB,113,113.00,63,55.75,50.11,92.48
9,MEM,SFB,MEM → SFB,101,101.00,56,55.45,65.46,121.07


In [78]:
plot_route = (
    top_route
    .sort_values("Delay_Rate")
    .copy()
)

max_idx = plot_route["Delay_Rate"].idxmax()

bar_colors = [
    COLORS["orange"]
    if idx == max_idx
    else COLORS["blue"]
    for idx in plot_route.index
]

fig = px.bar(
    plot_route,
    x="Delay_Rate",
    y="Route",
    orientation="h",
    labels={
        "Delay_Rate": "Tỷ lệ chậm (%)",
        "Route": "Tuyến bay"
    },
    text="Delay_Rate"
)

fig.update_traces(
    marker_color=bar_colors,
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Top 10 tuyến có tỷ lệ chậm cao nhất"
)

fig.show()

## 21. Phân tích nguyên nhân chậm chuyến

In [79]:
causes = pd.read_csv(
    ANALYSIS_DIR / "delay_causes.csv"
)

causes

,Delay_Cause,Delay_Minutes,Percentage
0,Late Aircraft,"43,862,971.00",39.19
1,Carrier,"36,326,377.00",32.45
2,NAS,"24,483,761.00",21.87
3,Weather,"7,108,714.00",6.35
4,Security,"152,802.00",0.14


In [80]:
cause_colors = [
    COLORS["blue"],
    COLORS["orange"],
    COLORS["orange_light"],
    COLORS["teal"],
    COLORS["blue_light"],
]

plot_causes = (
    causes
    .sort_values(
        "Delay_Minutes",
        ascending=False
    )
    .copy()
)

fig = px.bar(
    plot_causes,
    x="Delay_Cause",
    y="Delay_Minutes",
    labels={
        "Delay_Cause": "Nguyên nhân",
        "Delay_Minutes": "Tổng số phút chậm"
    },
    text="Percentage"
)

fig.update_traces(
    marker_color=cause_colors[:len(plot_causes)],
    texttemplate="%{text:.2f}%",
    textposition="outside"
)

style_figure(
    fig,
    "Tổng số phút chậm theo nguyên nhân"
)

fig.show()

In [81]:
highest_cause = causes.loc[
    causes["Delay_Minutes"].idxmax()
]

print(
    f"Nguyên nhân đóng góp nhiều phút chậm nhất: "
    f"{highest_cause['Delay_Cause']} "
    f"({highest_cause['Percentage']:.2f}%)"
)

Nguyên nhân đóng góp nhiều phút chậm nhất: Late Aircraft (39.19%)


## 22. Heatmap ngày × khung giờ

In [82]:
heatmap = pd.read_csv(
    ANALYSIS_DIR / "delay_heatmap.csv"
)

heatmap = heatmap.sort_values("DayOfWeek")

heatmap

,DayOfWeek,Day_Name,00-05,06-08,09-11,12-14,15-17,18-20,21-23
0,1,Monday,10.14,13.05,18.53,24.26,30.35,32.33,28.04
1,2,Tuesday,8.75,10.50,14.28,18.45,23.83,24.98,20.73
2,3,Wednesday,8.95,10.67,14.71,19.49,25.17,26.63,21.78
3,4,Thursday,7.80,11.39,16.72,22.88,31.21,34.22,28.97
4,5,Friday,8.58,11.73,17.33,23.83,30.48,32.79,28.30
5,6,Saturday,10.16,12.92,17.42,21.14,26.19,27.88,24.36
6,7,Sunday,9.72,13.12,19.28,26.42,33.87,37.53,33.84


In [83]:
time_columns = [
    col
    for col in time_order
    if col in heatmap.columns
]

fig = px.imshow(
    heatmap[time_columns].to_numpy(),
    x=time_columns,
    y=heatmap["Day_Name"],
    text_auto=".1f",
    aspect="auto",
    color_continuous_scale=[
        [0.00, COLORS["blue_soft"]],
        [0.45, COLORS["blue_light"]],
        [0.70, COLORS["orange_light"]],
        [0.88, COLORS["orange"]],
        [1.00, COLORS["red"]],
    ],
    labels={
        "x": "Khung giờ",
        "y": "Ngày",
        "color": "Delay Rate (%)"
    }
)

style_figure(
    fig,
    "Heatmap tỷ lệ chậm theo ngày và khung giờ"
)

fig.show()

## 23. Tóm tắt insight tự động

In [84]:
print("TÓM TẮT KẾT QUẢ EDA")
print("=" * 60)

print(
    f"1. Tổng số chuyến: "
    f"{get_metric('Total Flights'):,.0f}"
)

print(
    f"2. Tỷ lệ chậm toàn năm: "
    f"{get_metric('Delay Rate (%)'):.2f}%"
)

print(
    f"3. Trễ trung bình của chuyến bị chậm: "
    f"{get_metric('Average Delay Minutes'):.2f} phút"
)

print(
    f"4. Tháng có Delay Rate cao nhất: "
    f"{highest_month['Month_Name']} "
    f"({highest_month['Delay_Rate']:.2f}%)"
)

print(
    f"5. Ngày có Delay Rate cao nhất: "
    f"{highest_day['Day_Name']} "
    f"({highest_day['Delay_Rate']:.2f}%)"
)

print(
    f"6. Khung giờ có Delay Rate cao nhất: "
    f"{highest_time_group['Time_Group']} "
    f"({highest_time_group['Delay_Rate']:.2f}%)"
)

print(
    f"7. Hãng có Delay Rate cao nhất: "
    f"{highest_airline[airline_label]} "
    f"({highest_airline['Delay_Rate']:.2f}%)"
)

print(
    f"8. Nguyên nhân đóng góp nhiều phút chậm nhất: "
    f"{highest_cause['Delay_Cause']} "
    f"({highest_cause['Percentage']:.2f}%)"
)

TÓM TẮT KẾT QUẢ EDA
1. Tổng số chuyến: 7,001,619
2. Tỷ lệ chậm toàn năm: 21.63%
3. Trễ trung bình của chuyến bị chậm: 74.77 phút
4. Tháng có Delay Rate cao nhất: July (28.15%)
5. Ngày có Delay Rate cao nhất: Sunday (25.63%)
6. Khung giờ có Delay Rate cao nhất: 18-20 (31.24%)
7. Hãng có Delay Rate cao nhất: Frontier Airlines Inc. (27.27%)
8. Nguyên nhân đóng góp nhiều phút chậm nhất: Late Aircraft (39.19%)


# Kết luận EDA

Quá trình khám phá dữ liệu cho thấy:

1. Dữ liệu sau tiền xử lý có cấu trúc phù hợp để phân tích và trực quan hóa.
2. Một số giá trị thiếu là hợp lý theo nghiệp vụ, đặc biệt đối với chuyến bị hủy hoặc chuyển hướng.
3. Giá trị `ArrDelay` âm được giữ lại vì thể hiện chuyến bay đến sớm.
4. Dữ liệu tồn tại các giá trị độ trễ lớn nhưng không tự động loại bỏ vì chúng có thể phản ánh sự kiện thực tế.
5. Tỷ lệ chậm chuyến có sự khác biệt theo tháng, ngày trong tuần, khung giờ, hãng hàng không, sân bay và tuyến bay.
6. Các bảng tổng hợp và insight từ EDA là cơ sở để lựa chọn KPI, biểu đồ và bộ lọc cho dashboard Streamlit.

## Quy ước màu

- **Xanh dương**: dữ liệu thông thường / xu hướng chính.
- **Cam**: giá trị cao nhất hoặc điểm cần chú ý.
- **Teal**: nhóm dữ liệu phụ.
- **Đỏ**: mức độ cảnh báo cao trên heatmap.
- **Xanh nhạt**: dữ liệu nền hoặc các giá trị còn lại.

